# LOKI Detector Diagnostics

This notebook contains some tools that can be used to investigate/debug the Loki detectors:

- `loki.diagnostics.load_detectors`: a detector data loader that can be used when traditional workflows fail
- `loki.LokiBankViewer`: a 2D view of all detector panels with sliders to select straw and layer
- `plopp.inspector`: allows to draw rectangles on 2D views to display spectra along a third dimension
- `loki.instrument_view`: a 3D view of the detector panels

In [1]:
import plopp as pp
import scipp as sc
from ess import loki
import ess.loki.data  # noqa: F401

%matplotlib widget

## Loading detector bank data

The 'official' way to load loki detector data is via the `LokiWorkflow`.

However, this can sometimes fail if some information in the file is missing, incomplete or incorrect.
When debugging detectors or instrument setup, it is useful to have a loader that does its best to load the data,
using fallback methods when information is missing.

Here we load all 9 detector banks from a Loki file using the 'fail-safe' `loki.diagnostics.load_detectors`:

In [2]:
file = loki.data.loki_coda_file()

data = loki.diagnostics.load_detectors(file)
data.keys()

dict_keys(['loki_detector_0', 'loki_detector_1', 'loki_detector_2', 'loki_detector_3', 'loki_detector_4', 'loki_detector_5', 'loki_detector_6', 'loki_detector_7', 'loki_detector_8'])

Note that the equivalent `loki.diagnostics.load_monitors` also exists.

## The `LokiBankViewer`

In [3]:
viewer = loki.LokiBankViewer(data.hist())

In [4]:
# The figures don't display well in the docs with ipympl,
# so we replace the widgets with a screenshot of the bank viewer for the docs.
import ipywidgets as ipw

file = open("../../_static/images/loki_bank_viewer.png", "rb")
viewer = ipw.Image(value=file.read(), format='png')

In [5]:
viewer

Image(value=b'\x89PNG\r\n\x1a\n\x00\x00\x00\rIHDR\x00\x00\x04\xda\x00\x00\x04\n\x08\x06\x00\x00\x00\x96\xb5\x1…

## Time dimension inspector

We can use the inspector tool (from [Plopp](https://scipp.github.io/plopp/plotting/inspector-plot.html))
to draw rectangles on detector banks and display a time (`event_time_offset`) spectrum in a second panel.

We first have to histogram the data in the `event_time_offset` dimension.

In [6]:
time_bins = sc.linspace(
    'event_time_offset',
    start=0.0,
    stop=1.0 / 14.0,
    num=201,
    unit='s',
).to(unit='ns')
dhist = data.hist(event_time_offset=time_bins)

The inspector plot accepts 3D data, so we sum over the `layer` and `straw` dimensions.

In [7]:
da = dhist['loki_detector_0'].sum(['layer', 'straw'])

p = pp.inspector(da, dim='event_time_offset', orientation='vertical', mode='rectangle', cmax=5)

In [8]:
tool = p.children[0].toolbar['inspect']
tool.value = True
tool._tool.click(27, 20)
tool._tool.click(141, 40)
tool._tool.click(252, 35)
tool._tool.click(412, 42)

In [9]:
p

Box(children=(InteractiveFigure(children=(HBar(), HBar(children=(VBar(children=(Toolbar(children=(ButtonTool(i…

## The instrument view

The `instrument_view` will display a 3D rendering of the detector pixels,
along with a slider to select slices in the `event_time_offset` dimension.

In [10]:
# Reduce number of pixels displayed to avoid size bloat in docs
dhist = dhist['pixel', ::4]['layer', ::2]

In [11]:
loki.instrument_view(dhist, dim='event_time_offset')

Figure(children=(HBar(children=(HTML(value=''),)), HBox(children=(VBar(children=(Toolbar(children=(ButtonTool(…